In [1]:
import pandas as pd
import plotly.express as px

p = "../data/processed/"
telemetry = pd.read_parquet(p + "telemetry.parquet")
failures  = pd.read_parquet(p + "failures.parquet")
maint     = pd.read_parquet(p + "maint.parquet")
errors    = pd.read_parquet(p + "errors.parquet")
machines  = pd.read_parquet(p + "machines.parquet")

print(telemetry.shape)
print(telemetry.columns.tolist())

(876100, 12)
['datetime', 'machineID', 'voltage', 'rotation', 'pressure', 'vibration', 'hours_this_year', 'model', 'age', 'operating_hours', 'temperature', 'fail_within_24h']


In [2]:
# Failures by component
by_part = failures["failure"].value_counts().reset_index()
px.bar(by_part, x="failure", y="count", title="Failures by component").show()

# Failures by machine model (total, and per machine)
f = failures.merge(machines, on="machineID")
by_model = f["model"].value_counts().reset_index()
px.bar(by_model, x="model", y="count", title="Total failures by machine model").show()

rate = (f.groupby("model").size() / machines["model"].value_counts()).reset_index()
rate.columns = ["model", "failures_per_machine"]
px.bar(rate, x="model", y="failures_per_machine", title="Failures per machine, by model").show()

### Failures by component

**Finding:** Comp2 causes the most failures (about 259 of 761, roughly 34%), followed by comp1 (about 192), comp4 (about 179) and comp3 (about 131). Comp2 fails about twice as often as comp3, so it should be the first priority for inspection and spare-parts planning.

### Total failures by machine model

**Finding:** Model3 has the most failures in total (about 220), followed by model1 (about 190), model4 (about 183) and model2 (about 168). The totals are fairly close, but they are misleading on their own. Model3 has the most failures because the factory has many more model3 machines, not because they fail more often. Per machine, model3 fails far less than model1, so the per-machine chart gives the fairer comparison.

### Failures per machine, by model

**Finding:** Model1 machines fail most often, at about 11.8 failures per machine, followed by model2 at about 9.9. Model3 (about 6.3) and model4 (about 5.7) fail far less, so a model1 machine fails roughly twice as often as a model4 machine. Model1 and model2 machines should be monitored more closely and considered for earlier maintenance.

In [3]:
fc = failures.groupby("machineID").size().rename("failure_count").reset_index()
per_machine = machines.merge(fc, on="machineID", how="left").fillna({"failure_count": 0})

px.scatter(per_machine, x="age", y="failure_count", color="model",
           title="Machine age vs number of failures").show()

print(per_machine.groupby("age")["failure_count"].mean().round(1))

age
0      4.0
1      5.7
2      6.3
3      6.2
4      6.3
5      5.2
6      6.5
7      5.3
8      5.0
9      4.8
10     5.3
11     5.5
12     4.5
14    10.4
15     9.3
16    10.2
17     8.4
18    10.0
19     9.5
20     9.7
Name: failure_count, dtype: float64


### Machine age vs number of failures

**Finding:** Machines aged 14 years or more fail far more often than younger ones, averaging about 8 to 10 failures per machine against about 4 to 6.5 for machines aged 0 to 12. The increase is a sharp step at age 14 rather than a gradual rise, and it appears across all four machine models. Machines over 14 years old should be prioritised for inspection and maintenance.

In [5]:
sample = telemetry.sample(100000, random_state=1)
sample["status"] = sample["fail_within_24h"].map({0: "Normal", 1: "Within 24h of failure"})

for col in ["vibration", "temperature", "voltage", "rotation", "pressure"]:
    px.box(sample, x="status", y=col, title=f"{col}: normal vs just before a failure").show()

print(telemetry.groupby("fail_within_24h")[["vibration", "temperature", "voltage", "rotation", "pressure"]].mean().round(1))

                 vibration  temperature  voltage  rotation  pressure
fail_within_24h                                                     
0                     40.3         70.1    170.7     447.2     100.8
1                     42.8         75.2    175.9     418.8     105.3


### Sensor behaviour before a failure

Comparing the 24 hours before a failure with normal operation:

- **Rotation** drops the most of the original sensors: 418.8 against 447.2 (6.3% lower).
- **Vibration** rises from 40.3 to 42.8 (6.0% higher).
- **Pressure** rises from 100.8 to 105.3 (4.5% higher).
- **Voltage** rises from 170.7 to 175.9 (3.1% higher).
- **Temperature** rises from 70.1 to 75.2 (7.2% higher).

**Finding:** machines show a consistent warning pattern before failing: slower rotation combined with higher vibration, pressure and voltage. The shifts are modest for any single reading, because normal readings vary a lot from hour to hour, so no single sensor can reliably predict a failure on its own. Watching several sensors together, or their rolling averages, is much more informative, which is why the prediction model uses 24-hour averages.

**Note:** temperature is an AI-generated column built to rise before failures, so its change reflects the synthetic design, not a real-world discovery. The other four sensors come from the original Azure data, so their differences are the genuine warning signs.

In [6]:
m = telemetry.groupby("fail_within_24h")[["vibration", "temperature", "voltage", "rotation", "pressure"]].mean()
normal, before = m.loc[0], m.loc[1]

print("### Sensor behaviour before a failure\n")
for col in m.columns:
    diff = before[col] - normal[col]
    pct = diff / normal[col] * 100
    direction = "higher" if diff > 0 else "lower"
    print(f"- **{col.capitalize()}:** averages {before[col]:.1f} in the 24 hours before a failure, against {normal[col]:.1f} in normal operation ({abs(pct):.1f}% {direction}).")

### Sensor behaviour before a failure

- **Vibration:** averages 42.8 in the 24 hours before a failure, against 40.3 in normal operation (6.0% higher).
- **Temperature:** averages 75.2 in the 24 hours before a failure, against 70.1 in normal operation (7.2% higher).
- **Voltage:** averages 175.9 in the 24 hours before a failure, against 170.7 in normal operation (3.1% higher).
- **Rotation:** averages 418.8 in the 24 hours before a failure, against 447.2 in normal operation (6.3% lower).
- **Pressure:** averages 105.3 in the 24 hours before a failure, against 100.8 in normal operation (4.5% higher).


In [7]:
m = maint[["datetime", "machineID"]].copy()
m["maint_date"] = m["datetime"]
m = m.sort_values("datetime")

fs = failures.sort_values("datetime")
gap = pd.merge_asof(fs, m, on="datetime", by="machineID",
                    direction="backward", allow_exact_matches=False)
gap["days_since_maint"] = (gap["datetime"] - gap["maint_date"]).dt.days

print(gap["days_since_maint"].describe().round(1))
print("Failures with no earlier maintenance:", gap["maint_date"].isna().sum())
px.histogram(gap, x="days_since_maint", nbins=40,
             title="Days since last maintenance at time of failure").show()

count    761.0
mean      20.8
std       15.8
min        0.0
25%       15.0
50%       15.0
75%       15.0
max      170.0
Name: days_since_maint, dtype: float64
Failures with no earlier maintenance: 0


### Days since last maintenance at failure

**Finding:** At least half of all failures happened exactly 15 days after the machine's last maintenance record. The average gap is 20.8 days, and the longest is 170 days. Every one of the 761 failures had an earlier maintenance record. This suggests the factory logs maintenance on a regular cycle of about 15 days, so most failures simply fall at the end of one cycle. Because maintenance is so regular, this measure cannot show whether longer gaps cause more failures. The long tail of gaps well above 15 days (up to 170 days) is where a machine went longest without service, and those cases deserve a closer look.

In [8]:
# 1. Is maintenance on a regular cycle? (gap between consecutive maintenance dates per machine)
md = maint.drop_duplicates(["machineID", "datetime"]).sort_values(["machineID", "datetime"])
cycle = md.groupby("machineID")["datetime"].diff().dt.days
print("Gap between consecutive maintenance dates (days):")
print(cycle.value_counts().head(6))

# 2. Days since the same component was last replaced, at the time of failure
mc = maint.rename(columns={"comp": "failure"})[["machineID", "failure", "datetime"]].copy()
mc["maint_date"] = mc["datetime"]
mc = mc.sort_values("datetime")
gap_c = pd.merge_asof(failures.sort_values("datetime"), mc, on="datetime",
                      by=["machineID", "failure"], direction="backward",
                      allow_exact_matches=False)
gap_c["days_since_same_comp"] = (gap_c["datetime"] - gap_c["maint_date"]).dt.days

print()
print(gap_c["days_since_same_comp"].describe().round(1))
print("Failures with no earlier replacement of that component:", gap_c["maint_date"].isna().sum())
px.histogram(gap_c, x="days_since_same_comp", nbins=40,
             title="Days since the same component was last replaced, at failure").show()

Gap between consecutive maintenance dates (days):
datetime
15.0     1928
30.0      229
45.0       69
60.0       29
75.0       21
105.0      20
Name: count, dtype: int64

count    761.0
mean      88.9
std       61.0
min        0.0
25%       45.0
50%       67.0
75%      118.0
max      395.0
Name: days_since_same_comp, dtype: float64
Failures with no earlier replacement of that component: 0


In [9]:
px.histogram(gap, x="days_since_maint", nbins=40,
             title="Days since last maintenance at time of failure").show()

px.histogram(gap_c, x="days_since_same_comp", nbins=40,
             title="Days since the same component was last replaced, at failure").show()

### Maintenance schedule and failures

**Finding:** Maintenance follows a fixed 15-day cycle. Of the gaps between consecutive maintenance dates, 1,928 are exactly 15 days, and the rest are multiples of 15 (30, 45, 60 and so on) where a visit was skipped. This explains why at least half of all failures fall exactly 15 days after the machine's last maintenance record.

### Days since the same component was last replaced

**Finding:** Failures occur a median of 67 days (mean 89) after the failing component was last replaced. The middle half of failures fall between 45 and 118 days, but the range is wide, from 0 to 395 days. All 761 failures had an earlier replacement of that component on record. Because the spread is so wide, time since replacement alone does not give a clean replacement interval. It would need to be combined with sensor readings, which is what the risk model does.

In [10]:
err_count = errors.groupby("machineID").size().rename("error_count").reset_index()
both = per_machine.merge(err_count, on="machineID", how="left").fillna({"error_count": 0})

print("Correlation between errors and failures:",
      round(both["error_count"].corr(both["failure_count"]), 2))

px.scatter(both, x="error_count", y="failure_count", color="model",
           trendline="ols", trendline_scope="overall",
           title="Errors vs failures per machine").show()

Correlation between errors and failures: 0.54


### Errors vs failures per machine

**Finding:** Machines that log more errors tend to fail more often, with a moderate positive correlation of 0.54. Error counts are a useful early indicator, so machines with a high error count should be flagged for inspection. The relationship is far from perfect, so errors alone cannot predict a failure and are best combined with sensor readings.